# Learned Stage-Wise Curvature Tuning on FashionMNIST

This notebook evaluates Learned Stage-Wise Curvature Tuning (SW-CT) on the FashionMNIST dataset using an ImageNet-pretrained ResNet-50.

FashionMNIST is a grayscale clothing image-classification dataset containing categories such as shirts, shoes, bags, and other apparel. Its image characteristics differ substantially from the natural RGB images used for ImageNet pretraining, providing another domain-shift setting for evaluating Learned SW-CT.

The experiments compare four conditions:

1. **Baseline** — the original pretrained ResNet with ReLU activations and a trained downstream classifier.
2. **Single-Parameter Curvature Tuning (S-CT)** — one global beta selected through validation-based exhaustive search.
3. **Learned SW-CT with fixed initialization** — four trainable stage-wise beta parameters initialized at 0.78.
4. **Learned SW-CT with random initialization** — four trainable stage-wise beta parameters independently initialized between 0.70 and 0.99.

Each condition is evaluated using seeds 42, 43, and 44.

Experiments are conducted for both 20 and 30 epochs to determine whether additional optimization improves classification performance or changes the learned stage-wise beta values.

Wall-clock execution time is also recorded to compare computational cost across Baseline, S-CT, and Learned SW-CT.

In [1]:
!nvidia-smi

Thu Oct  8 16:42:52 2026       
+-----------------------------------------------------------------------------------------+
| NVIDIA-SMI 615.71.09              KMD Version: 615.71.09     CUDA UMD Version: 13.4     |
+-----------------------------------------+------------------------+----------------------+
| GPU  Name                 Persistence-M | Bus-Id          Disp.A | Volatile Uncorr. ECC |
| Fan  Temp   Perf          Pwr:Usage/Cap |           Memory-Usage | GPU-Util  Compute M. |
|                                         |                        |               MIG M. |
|=========================================+========================+======================|
|   0  NVIDIA L4                      Off |   00000000:00:03.0 Off |                    0 |
| N/A   43C    P8             12W /   72W |       0MiB /  23034MiB |      0%      Default |
|                                         |                        |                  N/A |
+-----------------------------------------+-----

In [9]:
%cd /content

!git clone -b main \
    https://github.com/NiftySnek173/research-curvature-tuning.git

%cd /content/research-curvature-tuning/src/curvature-tuning

!git branch --show-current
!git log -1 --oneline

/content
fatal: destination path 'curvature-tuning-research' already exists and is not an empty directory.
/content/curvature-tuning-research/src/curvature-tuning
stage-wise-ct
27ee9f0 (HEAD -> stage-wise-ct, origin/stage-wise-ct, origin/HEAD) updated food 101 execution


## Environment Setup

The repository dependencies are installed before running the experiments.

After installation, the Colab runtime should be restarted so that the required package versions are loaded correctly.

In [10]:
%pip install -q -r requirements.txt
%pip install --force-reinstall --no-cache-dir "numpy==1.26.3"

Note: you may need to restart the kernel to use updated packages.
   ━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━━ 18.3/18.3 MB 146.7 MB/s  0:00:00
  Attempting uninstall: numpy
    Found existing installation: numpy 1.26.3
    Uninstalling numpy-1.26.3:
      Successfully uninstalled numpy-1.26.3
Note: you may need to restart the kernel to use updated packages.


In [1]:
%cd /content/research-curvature-tuning/src/curvature-tuning

import os
import torch

os.environ["WANDB_MODE"] = "disabled"

print("Working directory:", os.getcwd())
print("PyTorch:", torch.__version__)
print("CUDA available:", torch.cuda.is_available())

if torch.cuda.is_available():
    print("GPU:", torch.cuda.get_device_name(0))

/content/curvature-tuning-research/src/curvature-tuning
Working directory: /content/curvature-tuning-research/src/curvature-tuning
PyTorch: 2.6.0+cu124
CUDA available: True
GPU: NVIDIA L4


## Arabic Digits Dataset

Before running the experiments, the Arabic Digits data loaders are checked to confirm that the downstream dataset can be loaded correctly.

The same dataset split and random seed protocol are used for Baseline, S-CT, and Learned SW-CT so that the methods are compared under the same conditions.

In [2]:
from utils.data import get_data_loaders

train_loader, test_loader, val_loader = get_data_loaders(
    "imagenet_to_fashion-mnist",
    train_batch_size=32,
    test_batch_size=128,
    seed=42,
)

print("Train samples:", len(train_loader.dataset))
print("Validation samples:", len(val_loader.dataset))
print("Test samples:", len(test_loader.dataset))

images, labels = next(iter(train_loader))

print("Image batch shape:", images.shape)
print("Label batch shape:", labels.shape)
print("Labels:", labels[:10])

/content/.venv/lib/python3.11/site-packages/tqdm/auto.py:21: TqdmWarning: IProgress not found. Please update jupyter and ipywidgets. See https://ipywidgets.readthedocs.io/en/stable/user_install.html
  from .autonotebook import tqdm as notebook_tqdm
Generating train split: 60000 examples [00:10, 5649.48 examples/s]
Generating test split: 10000 examples [00:01, 5710.38 examples/s]


Train samples: 48000
Validation samples: 12000
Test samples: 10000
Image batch shape: torch.Size([32, 3, 224, 224])
Label batch shape: torch.Size([32])
Labels: tensor([4, 5, 6, 2, 5, 9, 3, 5, 6, 5])


# ResNet-50 Experiments

ResNet-50 is evaluated first because it was used during the initial development of Learned SW-CT.

The experiment compares Baseline, S-CT, fixed-initialization SW-CT, and random-initialization SW-CT.

All methods use the same ImageNet-pretrained backbone, Arabic Digits dataset split, experimental seeds, and downstream training protocol.

## ResNet-50 — 20-Epoch Evaluation

The first evaluation uses 20 training epochs.

This provides the primary reference experiment and maintains compatibility with the earlier Learned SW-CT work.

### Methods

**Baseline**

The pretrained ResNet-50 retains its original ReLU activations. The backbone is frozen and only the downstream classifier is trained.

**S-CT**

The original Single-Parameter Curvature Tuning method searches over a single beta shared throughout the network. Candidate beta values from 0.70 to 1.00 are evaluated using validation performance, and the best candidate is evaluated on the test set.

The recorded S-CT execution time includes the complete beta search rather than only the final selected beta.

**Learned SW-CT — Fixed Initialization**

Four trainable beta parameters are assigned to the four ResNet stages. All four begin at beta = 0.78.

This preserves the initialization used in the original Learned SW-CT experiments.

**Learned SW-CT — Random Initialization**

Four trainable stage-wise beta parameters are initialized independently between 0.70 and 0.99.

The random initialization is generated deterministically from the experiment seed. This allows the experiment to test whether Learned SW-CT depends on the fixed 0.78 starting value while remaining reproducible.

In [3]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds fashion-mnist \
    --seed 42 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-05 17:31:56.308 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_fashion-mnist_resnet50_seed42_epochs20.log
2026-10-05 17:31:56.314 | INFO     | __main__:main:78 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /root/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100%|███████████████████████████████████████| 97.8M/97.8M [00:00<00:00, 161MB/s]
2026-10-05 17:33:25.989 | INFO     | __main__:main:105 - Testing baseline...
2026-10-05 17:33:26.068 | INFO     | __main__:main:116 - Number of trainable parameters: 20490
2026-10-05 17:33:26.068 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-05 17:36:52.846 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.407486, Accuracy: 9.38%
2026-10-05 17:36:53.308 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.207114, Accuracy: 20.42%
2026-10-05 17:36:53.664 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.8

In [4]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds fashion-mnist \
    --seed 43 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-05 22:22:34.877 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_fashion-mnist_resnet50_seed43_epochs20.log
2026-10-05 22:22:34.882 | INFO     | __main__:main:78 - Running on cuda
2026-10-05 22:24:07.678 | INFO     | __main__:main:105 - Testing baseline...
2026-10-05 22:24:07.747 | INFO     | __main__:main:116 - Number of trainable parameters: 20490
2026-10-05 22:24:07.748 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-05 22:27:41.942 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.301911, Accuracy: 9.38%
2026-10-05 22:27:42.380 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.169816, Accuracy: 29.42%
2026-10-05 22:27:42.793 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.848794, Accuracy: 49.69%
2026-10-05 22:27:43.204 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.570719, Accuracy: 58.41%
2026-10-05 22:27:43.636 | INFO     | train:train_epoch:47 - Epoch 1, Step 400,

In [3]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds fashion-mnist \
    --seed 44 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 20

2026-10-06 03:36:49.292 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_fashion-mnist_resnet50_seed44_epochs20.log
2026-10-06 03:36:49.296 | INFO     | __main__:main:78 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /root/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100%|███████████████████████████████████████| 97.8M/97.8M [00:00<00:00, 189MB/s]
2026-10-06 03:38:03.233 | INFO     | __main__:main:105 - Testing baseline...
2026-10-06 03:38:03.304 | INFO     | __main__:main:116 - Number of trainable parameters: 20490
2026-10-06 03:38:03.304 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-06 03:41:19.976 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.382844, Accuracy: 9.38%
2026-10-06 03:41:20.347 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.208515, Accuracy: 24.29%
2026-10-06 03:41:20.695 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.8

### Learned SW-CT with Fixed Beta Initialization

The original Learned SW-CT configuration is first reproduced using the fixed initialization:

\[[\beta_1,\beta_2,\beta_3,\beta_4]=[0.78,0.78,0.78,0.78].\]

The initial value is only a starting point. During training, the four beta parameters are optimized independently together with the downstream classifier.

These runs provide the reference against which random initialization will be compared.

In [4]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds fashion-mnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-06 08:03:35.912 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_fashion-mnist_resnet50_seed42_epochs20_initfixed0.78_betalr0.01.log
2026-10-06 08:03:35.992 | INFO     | __main__:main:302 - Running on cuda
2026-10-06 08:04:55.690 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-06 08:04:55.691 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-06 08:04:55.760 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-06 08:04:55.761 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-06 08:04:55.761 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-06 08:04:57.265 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.393544, Accuracy: 9.38%
2026-10-06 08:05:53.654 | INFO     | train:train_e

In [3]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds fashion-mnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-06 13:40:25.846 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_fashion-mnist_resnet50_seed43_epochs20_initfixed0.78_betalr0.01.log
2026-10-06 13:40:25.906 | INFO     | __main__:main:302 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /root/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100%|███████████████████████████████████████| 97.8M/97.8M [00:00<00:00, 217MB/s]
2026-10-06 13:41:47.023 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-06 13:41:47.024 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-06 13:41:47.145 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-06 13:41:47.147 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-06 13:41:47.147 | INFO     |

In [20]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds fashion-mnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 20

2026-10-08 16:46:52.379 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_fashion-mnist_resnet50_seed44_epochs20_initfixed0.78_betalr0.01.log
2026-10-08 16:46:52.432 | INFO     | __main__:main:302 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /content/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100%|███████████████████████████████████████| 97.8M/97.8M [00:00<00:00, 245MB/s]
2026-10-08 16:47:46.027 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-08 16:47:46.028 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-08 16:47:46.103 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-08 16:47:46.103 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-08 16:47:46.104 | INFO   

### Learned SW-CT with Random Beta Initialization

The fixed beta = 0.78 initialization may raise the question of whether Learned SW-CT performs well only because its starting point was informed by the earlier S-CT experiments.

To test this dependency, each of the four stage-wise beta parameters is now initialized independently from a uniform distribution between 0.70 and 0.99.

The initialization is reproducible: the random generator is seeded using the experiment seed. Therefore, each seed always receives the same initial beta vector.

If random initialization produces similar performance to the fixed 0.78 experiment, this provides evidence that the Learned SW-CT result is not dependent on a single hand-selected initialization.

In [21]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds fashion-mnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-08 20:20:30.783 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_fashion-mnist_resnet50_seed42_epochs20_initrandom_betalr0.01.log
2026-10-08 20:20:30.836 | INFO     | __main__:main:302 - Running on cuda
2026-10-08 20:21:23.653 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-08 20:21:23.654 | INFO     | __main__:main:394 - Requested initial stage betas: [0.924447, 0.827275, 0.948993, 0.902237]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-08 20:21:23.717 | INFO     | __main__:main:418 - Initial stage betas: [0.924447238445282, 0.827274739742279, 0.9489933848381042, 0.9022367000579834]
2026-10-08 20:21:23.718 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-08 20:21:23.718 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-08 20:21:24.802 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.349760, Accuracy: 9.38%
2026-10-08 20:22:03.396 | INFO     | t

In [22]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds fashion-mnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-08 23:54:06.887 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_fashion-mnist_resnet50_seed43_epochs20_initrandom_betalr0.01.log
2026-10-08 23:54:06.939 | INFO     | __main__:main:302 - Running on cuda
2026-10-08 23:55:00.179 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-08 23:55:00.180 | INFO     | __main__:main:394 - Requested initial stage betas: [0.889167, 0.712695, 0.705809, 0.943372]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-08 23:55:00.241 | INFO     | __main__:main:418 - Initial stage betas: [0.8891667127609253, 0.7126947641372681, 0.7058085799217224, 0.9433716535568237]
2026-10-08 23:55:00.242 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-08 23:55:00.242 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-08 23:55:01.326 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.332443, Accuracy: 18.75%
2026-10-08 23:55:39.913 | INFO     

In [23]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds fashion-mnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 20

2026-10-09 03:27:34.124 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_fashion-mnist_resnet50_seed44_epochs20_initrandom_betalr0.01.log
2026-10-09 03:27:34.176 | INFO     | __main__:main:302 - Running on cuda
2026-10-09 03:28:27.254 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-09 03:28:27.254 | INFO     | __main__:main:394 - Requested initial stage betas: [0.735544, 0.774853, 0.817674, 0.981063]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-09 03:28:27.318 | INFO     | __main__:main:418 - Initial stage betas: [0.7355440258979797, 0.7748528122901917, 0.8176735043525696, 0.9810633659362793]
2026-10-09 03:28:27.319 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-09 03:28:27.320 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-09 03:28:28.415 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.466886, Accuracy: 0.00%
2026-10-09 03:29:07.026 | INFO     |

# ResNet-50 — 30-Epoch Evaluation

The same experiments are now repeated for 30 epochs.

The purpose of increasing the training budget is to determine whether the 20-epoch results are limited by insufficient optimization.

If a method improves substantially with 30 epochs, this suggests that additional optimization is useful. If performance remains similar, it indicates that the method has largely stabilized within the original 20-epoch training budget.

All other experimental settings remain unchanged.

For random-initialization SW-CT, the same seed produces exactly the same initial four-beta vector in both the 20-epoch and 30-epoch experiments. Therefore, initialization is held constant while the training duration changes.

Execution time is again recorded to measure the computational cost of extending training from 20 to 30 epochs.

In [24]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds fashion-mnist \
    --seed 42 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-09 07:01:13.655 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_fashion-mnist_resnet50_seed42_epochs30.log
2026-10-09 07:01:13.657 | INFO     | __main__:main:78 - Running on cuda
2026-10-09 07:02:07.143 | INFO     | __main__:main:105 - Testing baseline...
2026-10-09 07:02:07.187 | INFO     | __main__:main:116 - Number of trainable parameters: 20490
2026-10-09 07:02:07.187 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-09 07:03:45.520 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.407408, Accuracy: 9.38%
2026-10-09 07:03:45.745 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.207121, Accuracy: 20.42%
2026-10-09 07:03:45.961 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.883954, Accuracy: 44.65%
2026-10-09 07:03:46.188 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.589749, Accuracy: 55.34%
2026-10-09 07:03:46.427 | INFO     | train:train_epoch:47 - Epoch 1, Step 400,

In [25]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds fashion-mnist \
    --seed 43 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-09 10:14:59.396 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_fashion-mnist_resnet50_seed43_epochs30.log
2026-10-09 10:14:59.397 | INFO     | __main__:main:78 - Running on cuda
2026-10-09 10:15:52.362 | INFO     | __main__:main:105 - Testing baseline...
2026-10-09 10:15:52.406 | INFO     | __main__:main:116 - Number of trainable parameters: 20490
2026-10-09 10:15:52.406 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-09 10:17:31.078 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.302006, Accuracy: 9.38%
2026-10-09 10:17:31.308 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.169824, Accuracy: 29.49%
2026-10-09 10:17:31.529 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.848794, Accuracy: 49.72%
2026-10-09 10:17:31.754 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.570726, Accuracy: 58.43%
2026-10-09 10:17:31.983 | INFO     | train:train_epoch:47 - Epoch 1, Step 400,

In [26]:
!WANDB_MODE=disabled python generalization_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds fashion-mnist \
    --seed 44 \
    --linear_probe_train_bs 32 \
    --linear_probe_test_bs 128 \
    --epochs 30

2026-10-09 13:28:59.535 | INFO     | __main__:main:74 - Log file: ./logs/generalization_ct_imagenet_to_fashion-mnist_resnet50_seed44_epochs30.log
2026-10-09 13:28:59.536 | INFO     | __main__:main:78 - Running on cuda
2026-10-09 13:29:53.233 | INFO     | __main__:main:105 - Testing baseline...
2026-10-09 13:29:53.276 | INFO     | __main__:main:116 - Number of trainable parameters: 20490
2026-10-09 13:29:53.276 | INFO     | __main__:main:117 - Starting transfer learning...
2026-10-09 13:31:32.119 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.382936, Accuracy: 9.38%
2026-10-09 13:31:32.346 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.208502, Accuracy: 24.29%
2026-10-09 13:31:32.574 | INFO     | train:train_epoch:47 - Epoch 1, Step 200, Loss: 1.887721, Accuracy: 44.29%
2026-10-09 13:31:32.798 | INFO     | train:train_epoch:47 - Epoch 1, Step 300, Loss: 1.594564, Accuracy: 54.90%
2026-10-09 13:31:33.017 | INFO     | train:train_epoch:47 - Epoch 1, Step 400,

In [27]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds fashion-mnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-09 16:43:28.404 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_fashion-mnist_resnet50_seed42_epochs30_initfixed0.78_betalr0.01.log
2026-10-09 16:43:28.458 | INFO     | __main__:main:302 - Running on cuda
2026-10-09 16:44:21.637 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-09 16:44:21.638 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-09 16:44:21.699 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-09 16:44:21.700 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-09 16:44:21.700 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-09 16:44:22.804 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.393601, Accuracy: 9.38%
2026-10-09 16:45:01.448 | INFO     | train:train_e

In [28]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds fashion-mnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-09 22:03:25.833 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_fashion-mnist_resnet50_seed43_epochs30_initfixed0.78_betalr0.01.log
2026-10-09 22:03:25.886 | INFO     | __main__:main:302 - Running on cuda
2026-10-09 22:04:19.170 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-09 22:04:19.170 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-09 22:04:19.234 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-09 22:04:19.235 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-09 22:04:19.235 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-09 22:04:20.355 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.341712, Accuracy: 18.75%
2026-10-09 22:04:59.020 | INFO     | train:train_

In [ ]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds fashion-mnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy fixed \
    --init_beta 0.78 \
    --beta_lr 0.01 \
    --epochs 30

2026-10-10 03:23:20.235 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_fashion-mnist_resnet50_seed44_epochs30_initfixed0.78_betalr0.01.log
2026-10-10 03:23:20.289 | INFO     | __main__:main:302 - Running on cuda
2026-10-10 03:24:13.131 | INFO     | __main__:main:389 - Initialization strategy: fixed
2026-10-10 03:24:13.131 | INFO     | __main__:main:394 - Requested initial stage betas: [0.78, 0.78, 0.78, 0.78]
2026-10-10 03:24:13.194 | INFO     | __main__:main:418 - Initial stage betas: [0.7799999713897705, 0.7799999713897705, 0.7799999713897705, 0.7799999713897705]
2026-10-10 03:24:13.195 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-10 03:24:13.195 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-10 03:24:14.309 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.500674, Accuracy: 3.12%
2026-10-10 03:24:52.975 | INFO     | train:train_epoch:47 - Epoch 1, Step 100, Loss: 2.254200,

In [8]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds fashion-mnist \
    --seed 42 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-10 12:29:47.010 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_fashion-mnist_resnet50_seed42_epochs30_initrandom_betalr0.01.log
2026-10-10 12:29:47.064 | INFO     | __main__:main:302 - Running on cuda
Downloading: "https://download.pytorch.org/models/resnet50-0676ba61.pth" to /home/anonymous/.cache/torch/hub/checkpoints/resnet50-0676ba61.pth
100%|███████████████████████████████████████| 97.8M/97.8M [00:00<00:00, 223MB/s]
2026-10-10 12:30:41.063 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-10 12:30:41.063 | INFO     | __main__:main:394 - Requested initial stage betas: [0.924447, 0.827275, 0.948993, 0.902237]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-10 12:30:41.140 | INFO     | __main__:main:418 - Initial stage betas: [0.924447238445282, 0.827274739742279, 0.9489933848381042, 0.9022367000579834]
2026-10-10 12:30:41.141 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-10 12:

In [9]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds fashion-mnist \
    --seed 43 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-10 17:49:29.052 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_fashion-mnist_resnet50_seed43_epochs30_initrandom_betalr0.01.log
2026-10-10 17:49:29.106 | INFO     | __main__:main:302 - Running on cuda
2026-10-10 17:50:22.254 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-10 17:50:22.255 | INFO     | __main__:main:394 - Requested initial stage betas: [0.889167, 0.712695, 0.705809, 0.943372]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-10 17:50:22.316 | INFO     | __main__:main:418 - Initial stage betas: [0.8891667127609253, 0.7126947641372681, 0.7058085799217224, 0.9433716535568237]
2026-10-10 17:50:22.317 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-10 17:50:22.318 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-10 17:50:23.405 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.332443, Accuracy: 18.75%
2026-10-10 17:51:02.010 | INFO     

In [10]:
!WANDB_MODE=disabled python generalization_stagewise_ct.py \
    --model resnet50 \
    --pretrained_ds imagenet \
    --transfer_ds fashion-mnist \
    --seed 44 \
    --transfer_train_bs 32 \
    --transfer_test_bs 128 \
    --init_strategy random \
    --beta_lr 0.01 \
    --epochs 30

2026-10-10 23:09:10.971 | INFO     | __main__:main:286 - Log file: ./logs/generalization_stagewise_ct_imagenet_to_fashion-mnist_resnet50_seed44_epochs30_initrandom_betalr0.01.log
2026-10-10 23:09:11.024 | INFO     | __main__:main:302 - Running on cuda
2026-10-10 23:10:04.288 | INFO     | __main__:main:389 - Initialization strategy: random
2026-10-10 23:10:04.288 | INFO     | __main__:main:394 - Requested initial stage betas: [0.735544, 0.774853, 0.817674, 0.981063]
Stage-Wise CT ReLU counts: [13, 16, 24, 12]
2026-10-10 23:10:04.350 | INFO     | __main__:main:418 - Initial stage betas: [0.7355440258979797, 0.7748528122901917, 0.8176735043525696, 0.9810633659362793]
2026-10-10 23:10:04.351 | INFO     | __main__:main:434 - Trainable curvature parameters: 4
2026-10-10 23:10:04.351 | INFO     | __main__:main:439 - Total trainable parameters: 20494
2026-10-10 23:10:05.438 | INFO     | train:train_epoch:47 - Epoch 1, Step 0, Loss: 2.466886, Accuracy: 0.00%
2026-10-10 23:10:44.052 | INFO     |